In [ ]:
import pandas as pd 
pd.set_option('display.max_columns', 500)
pd.set_option('display.max_rows', 10000)
pd.set_option('display.width', 1000)


sheets = pd.ExcelFile(f'./PQM - podatki za pilotni projekt (OCR12VM) - ENG.xlsx')
print(sheets.sheet_names)

data = pd.read_excel(f'./PQM - podatki za pilotni projekt (OCR12VM) - ENG.xlsx', sheet_name='Table1 (basic)', skiprows=[0])
data.drop(['QualityRequirement', 'QualNo', 'CustID','CustVer','InternalVer','MetalRavneQualityName','SteelGroup','Month','Year'], axis=1, inplace=True)
data.drop_duplicates(subset=['HeatNo'],keep='first',inplace=True)

data.dropna(subset=['Cr_Last_EOP','Mo_Last_EOP','Ni_Last_EOP','V_Last_EOP','W_Last_EOP'],inplace=True)


data_=pd.read_excel('PQM - podatki za pilotni projekt (OCR12VM) - ENG.xlsx',sheet_name='Table2 (limits)',skiprows=[0])
data_.drop(['QualityRequirement','QualNo','CustID','CustVer','InternalVer','MetalRavneQualityName','SteelGroup','Month','Year'],axis=1,inplace=True)
data_.drop(['Date','Cr_Final','Ni_Final','Mo_Final','V_Final','W_Final'],axis=1,inplace=True)
data_.drop_duplicates(subset=['HeatNo'], keep='first', inplace=True)

data=data.merge(data_,on='HeatNo',how='inner') 

data_=pd.read_excel('PQM - podatki za pilotni projekt (OCR12VM) - ENG.xlsx',sheet_name='Table4 (alloys)',skiprows=[0])
data.drop(['LFVD_FeCrA', 'LFVD_FeCrC','LFVD_NiGran', 'LFVD_NiKatode','LFVD_FeMo', 'LFVD_Polymox','LFVD_FeV','LFVD_FeW72','LFVD_WPaketi'],axis=1,inplace=True)
data_.drop_duplicates(subset=['HeatNo'], keep='first', inplace=True)

data=data.merge(data_,on='HeatNo',how='inner')

# data_=pd.read_excel('PQM - podatki za pilotni projekt (OCR12VM) - ENG.xlsx',sheet_name='Table7 (head)',skiprows=[0])
# data_.drop_duplicates(subset=['HeatNo'], keep='first', inplace=True)

# data=data.merge(data_,on='HeatNo',how='inner') # толоько для нахождения брака у работников

data_=pd.read_excel('PQM - podatki za pilotni projekt (OCR12VM) - ENG.xlsx',sheet_name='Table8 (scrap)',skiprows=[0])
data_.drop_duplicates(subset=['HeatNo'], keep='first', inplace=True)

data=data.merge(data_,on='HeatNo',how='inner')

data_=pd.read_excel('PQM - podatki za pilotni projekt (OCR12VM) - ENG.xlsx',sheet_name='Table9 (all. scr.)',skiprows=[0])
data_.drop_duplicates(subset=['HeatNo'], keep='first', inplace=True)

data=data.merge(data_,on='HeatNo',how='inner')

data_=pd.read_excel('PQM - podatki za pilotni projekt (OCR12VM) - ENG.xlsx',sheet_name='Table10 (unall. scr.)',skiprows=[0])
data_.drop_duplicates(subset=['HeatNo'], keep='first', inplace=True)

data=data.merge(data_,on='HeatNo',how='inner')

display(data.head(3))
print('всего строк=',len(data))
print('всего столбцов=',len(data.columns))
data.to_csv('итоговая таблица.csv',sep=';',index=False)

### Удаление данных с нулевой диссперсией

In [ ]:
import pandas as pd
pd.set_option('display.max_rows', 10000)
pd.set_option('display.max_columns', 500)
pd.set_option('display.width', 1000)

import plotly.graph_objects as go
from plotly.subplots import make_subplots
data=pd.read_csv('итоговая таблица.csv',sep=';')
#LFVD_CaS LFVD_CoMet  LFVD_Cu LFVD_FeB	LFVD_FeBŽica	LFVD_FeCrNit  LFVD_FeMnA  LFVD_FeNbTa	LFVD_FeNbTafi13 LFVD_FeSiZrŽica	LFVD_FeTi	LFVD_FeTifi13
#LFVD_NiKatode	LFVD_NiOksid	LFVD_OdpCu  LFVD_SiMet  LFVD_KarboritZaVpih	LFVD_Ni90 

display(data.describe())
del_=[]
for i in data.describe().columns:
    if data.describe().loc['std',i]==0:
        del_.append(i)

del_.remove('Ni_LowerLimit')
del_.remove('Ni_Target')
del_.remove('W_LowerLimit')
del_.remove('W_Target')

data.drop(del_,axis=1,inplace=True)
data.drop(['Fill#1_ScrapName','Fill#1_ScrapWeight','Fill#2_ScrapName','Fill#2_ScrapWeight','Fill#3_ScrapName','Fill#3_ScrapWeight','Fill#4_ScrapName',
          'Fill#4_ScrapWeight','Fill#5_ScrapName','Fill#5_ScrapWeight','Fill#6_ScrapName','Fill#6_ScrapWeight'],axis=1,inplace=True)

print('всего строк=',len(data))
print('всего столбцов=',len(data.columns))
data.to_csv('итоговая таблица_испр.csv',sep=';',index=False)

### Проверка взаимных корреляций

In [ ]:
import pandas as pd
pd.set_option('display.max_rows', 10000)
pd.set_option('display.max_columns', 500)
pd.set_option('display.width', 1000)

import plotly.graph_objects as go
from plotly.subplots import make_subplots
data=pd.read_csv('итоговая таблица_испр.csv',sep=';')
data_=data.drop(['HeatNo','Date'],axis=1)

corr=data_.corr()

print('число столбцов в таблице=',len(data_.corr()))

display(corr.head(3))
gran_corr_value=0.8
corr_={i:[] for i in corr.columns}
for i in range(len(corr.columns)):    
    mas=corr[corr.columns[i]].tolist()
    el=mas[i]
    ind_max=[j for j in range(len(mas)) if (mas[j]>gran_corr_value)&(j!=i)]
    mas.remove(mas[i])
    corr_[corr.columns[i]]=[min(mas),max(mas)]+[corr.columns[j] for j in ind_max]
    print(corr.columns[i],':',corr_[corr.columns[i]])



### Гистограмма превышения целевого значения по компонентам

#### TODO
- создать гистограммы по отдельным сталеварам
- выявить случаи брака, превышение или занижение по элементу

In [ ]:
import plotly.graph_objects as go
from plotly.subplots import make_subplots

data['Cr_exceed']=data.apply(lambda x:x['Cr_Final']-x['Cr_Target'],axis=1)
data['Ni_exceed']=data.apply(lambda x:x['Ni_Final']-x['Ni_Target'],axis=1)
data['Mo_exceed']=data.apply(lambda x:x['Mo_Final']-x['Mo_Target'],axis=1)
data['V_exceed']=data.apply(lambda x:x['V_Final']-x['V_Target'],axis=1)
data['W_exceed']=data.apply(lambda x:x['W_Final']-x['W_Target'],axis=1)

print('в среднем разница между Cr_Target и Cr_LowerLimit =',data.apply(lambda x:x['Cr_Target']-x['Cr_LowerLimit'],axis=1).mean())
print('в среднем разница между Ni_Target и Ni_LowerLimit =',data.apply(lambda x:x['Ni_Target']-x['Ni_LowerLimit'],axis=1).mean())
print('в среднем разница между Mo_Target и Mo_LowerLimit =',data.apply(lambda x:x['Mo_Target']-x['Mo_LowerLimit'],axis=1).mean())
print('в среднем разница между V_Target и V_LowerLimit =',data.apply(lambda x:x['V_Target']-x['V_LowerLimit'],axis=1).mean())
print('в среднем разница между W_Target и W_LowerLimit =',data.apply(lambda x:x['W_Target']-x['W_LowerLimit'],axis=1).mean())

fig = make_subplots(specs=[[{"secondary_y": True}]])

fig.add_trace(go.Histogram(x=data['Cr_exceed'],xbins=dict(start=-0.2, end= 0.2, size=0.005), name='Гистограмма превышения Cr'))
fig.add_trace(go.Histogram(x=data['Ni_exceed'],xbins=dict(start=-0.5, end= 0.5, size=0.005), name='Гистограмма превышения Ni'))
fig.add_trace(go.Histogram(x=data['Mo_exceed'],xbins=dict(start=-0.2, end= 0.2, size=0.005), name='Гистограмма превышения Mo'))
fig.add_trace(go.Histogram(x=data['V_exceed'],xbins=dict(start=-0.2, end= 0.2, size=0.005), name='Гистограмма превышения V'))
fig.add_trace(go.Histogram(x=data['W_exceed'],xbins=dict(start=-0.2, end= 0.2, size=0.005), name='Гистограмма превышения W'))
#fig.add_trace(go.Histogram(x=data['Cr_exceed'], name='Гистограмма превышения Cr'))
fig.show()

In [ ]:
data['Cr_adviser_target']=data.apply(lambda x:(x['Cr_Target']+x['Cr_LowerLimit'])/2,axis=1)
data['Ni_adviser_target']=data.apply(lambda x:(x['Ni_Target']+x['Ni_LowerLimit'])/2,axis=1)
data['Cr_exceed']=data.apply(lambda x:x['Cr_Final']-x['Cr_adviser_target'],axis=1)
data['Ni_exceed']=data.apply(lambda x:x['Ni_Final']-x['Ni_adviser_target'],axis=1)

print('в среднем разница между Cr_Target и Cr_LowerLimit =',data.apply(lambda x:x['Cr_Target']-x['Cr_LowerLimit'],axis=1).mean())
print('в среднем разница между Ni_Target и Ni_LowerLimit =',data.apply(lambda x:x['Ni_Target']-x['Ni_LowerLimit'],axis=1).mean())

fig = make_subplots(specs=[[{"secondary_y": True}]])

fig.add_trace(go.Histogram(x=data['Cr_exceed'],xbins=dict(start=-0.2, end= 0.2, size=0.005), name='Гистограмма превышения Cr'))
fig.add_trace(go.Histogram(x=data['Ni_exceed'],xbins=dict(start=-0.5, end= 0.5, size=0.005), name='Гистограмма превышения Ni'))
#fig.add_trace(go.Histogram(x=data['Cr_exceed'], name='Гистограмма превышения Cr'))
fig.show()

### Экономический эффект

In [ ]:
display(data[['TotalIngotsWeight','Cr_Last_EOP','Cr_Final','LFVD_FeCrA','LFVD_FeCrC',]].head(3))
print('количество строк с большим исходным составом=',len(data[(data['LFVD_FeCrA']==0)&(data['LFVD_FeCrC']==0)&(data['LFVD_FeCrCSi']==0)&(data['LFVD_FeCrC51']==0)]))

display(data[['TotalIngotsWeight','Ni_Last_EOP','Ni_Final','LFVD_NiGran']].head(3))
print('количество строк с большим исходным составом=',len(data[(data['LFVD_NiGran']==0)]))

display(data[['TotalIngotsWeight','Mo_Last_EOP','Mo_Final','LFVD_FeMo','LFVD_Polymox']].head(3))
print('количество строк с большим исходным составом=',len(data[(data['LFVD_FeMo']==0)&(data['LFVD_Polymox']==0)]))

display(data[['TotalIngotsWeight','V_Last_EOP','V_Final','LFVD_FeV']].head(3))
print('количество строк с большим исходным составом=',len(data[(data['LFVD_FeV']==0)]))

display(data[['TotalIngotsWeight','W_Last_EOP','W_Final','LFVD_FeW72']].head(3))
print('количество строк с большим исходным составом=',len(data[(data['LFVD_FeW72']==0)]))

In [ ]:
data_cr=data[(data['Cr_Final']>data['Cr_Last_EOP'])&(data['Cr_Final']>data['Cr_Target'])]
data_cr=data_cr.copy()

data_cr['FeCr_1%']=data_cr.apply(lambda x: (x['LFVD_FeCrA']+x['LFVD_FeCrC'])/(x['Cr_Final']-x['Cr_Last_EOP'])/x['TotalIngotsWeight']*100,axis=1)
data_cr['Cr_surplus']=data_cr.apply(lambda x:(x['LFVD_FeCrA']+x['LFVD_FeCrC'])-(x['Cr_Target']-x['Cr_Last_EOP'])*x['TotalIngotsWeight']*x['FeCr_1%']/100,axis=1)
display(data_cr[['TotalIngotsWeight','Cr_Last_EOP','Cr_Target','Cr_Final','LFVD_FeCrA','LFVD_FeCrC','FeCr_1%','Cr_surplus']].head(3))
print('перерасход в год FeCr=',round(data_cr['Cr_surplus'].sum()/10,0),'кг',' примерная стоимость=',round(data_cr['Cr_surplus'].sum()/10*300/1000000,2),'млн.руб')

In [ ]:
data_mo=data[(data['Mo_Final']>data['Mo_Last_EOP'])&(data['Mo_Final']>data['Mo_Target'])]
data_mo=data_mo.copy()

data_mo['FeMo_1%']=data_mo.apply(lambda x: (x['LFVD_FeMo']+x['LFVD_Polymox'])/(x['Mo_Final']-x['Mo_Last_EOP'])/x['TotalIngotsWeight']*100,axis=1)
data_mo['Mo_surplus']=data_mo.apply(lambda x:(x['LFVD_FeMo']+x['LFVD_Polymox'])-(x['Mo_Target']-x['Mo_Last_EOP'])*x['TotalIngotsWeight']*x['FeMo_1%']/100,axis=1)
display(data_mo[['TotalIngotsWeight','Mo_Last_EOP','Mo_Target','Mo_Final','LFVD_FeMo','FeMo_1%','Mo_surplus']].head(3))
print('перерасход в год Mo=',round(data_mo['Mo_surplus'].sum()/10,0),'кг',' примерная стоимость=',round(data_mo['Mo_surplus'].sum()/10*1500/1000000,2),'млн.руб')

In [ ]:
data_v=data[(data['V_Final']>data['V_Last_EOP'])&(data['V_Final']>data['V_Target'])]
data_v=data_v.copy()

data_v['FeV_1%']=data_v.apply(lambda x: (x['LFVD_FeV'])/(x['V_Final']-x['V_Last_EOP'])/x['TotalIngotsWeight']*100,axis=1)
data_v['V_surplus']=data_v.apply(lambda x:(x['LFVD_FeV'])-(x['V_Target']-x['V_Last_EOP'])*x['TotalIngotsWeight']*x['FeV_1%']/100,axis=1)
display(data_v[['TotalIngotsWeight','V_Last_EOP','V_Target','V_Final','LFVD_FeV','FeV_1%','V_surplus']].head(3))
print('перерасход в год V=',round(data_v['V_surplus'].sum()/10,0),'кг',' примерная стоимость=',round(data_v['V_surplus'].sum()/10*1500/1000000,2),'млн.руб')

In [ ]:
data_w=data[(data['W_Final']>data['W_Last_EOP'])&(data['W_Final']>data['W_Target'])]
data_w=data_w.copy()

data_w['FeW_1%']=data_w.apply(lambda x: (x['LFVD_FeW72'])/(x['W_Final']-x['W_Last_EOP'])/x['TotalIngotsWeight']*100,axis=1)
data_w['W_surplus']=data_w.apply(lambda x:(x['LFVD_FeW72'])-(x['W_Target']-x['W_Last_EOP'])*x['TotalIngotsWeight']*x['FeW_1%']/100,axis=1)
display(data_w[['TotalIngotsWeight','W_Last_EOP','W_Target','W_Final','LFVD_FeW72','FeW_1%','W_surplus']].head(3))
print('перерасход в год W=',round(data_w['W_surplus'].sum()/10,0),'кг',' примерная стоимость=',round(data_w['W_surplus'].sum()/10*1500/1000000,2),'млн.руб')

### Данные по отдельным сталеварам

In [ ]:
#'Cr_surplus', 'Mo_surplus', 'V_surplus', 'W_surplus', 'Total_defects' 
data_unique_emp = pd.DataFrame(data['LFVD_ShiftHead'].unique(), columns=['LFVD_ShiftHead'])

fig = make_subplots(specs=[[{"secondary_y": True}]])

for emp in data_unique_emp['LFVD_ShiftHead']:
    deffects = data.agg(lambda x: 1 if x['LFVD_ShiftHead']==emp and (x['Cr_Final'] > x['Cr_Last_EOP']) and (x['Cr_Final'] > x['Cr_Target']) else 0, axis=1).sum()
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Cr_defects']=deffects 
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Total_defects']=deffects
    deffects = data.agg(lambda x: 1 if x['LFVD_ShiftHead']==emp and (x['Ni_Final'] > x['Ni_Last_EOP']) and (x['Ni_Final'] > x['Ni_Target']) else 0, axis=1).sum()
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Ni_defects']=deffects 
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Total_defects']+=deffects
    deffects = data.agg(lambda x: 1 if x['LFVD_ShiftHead']==emp and (x['Mo_Final'] > x['Mo_Last_EOP']) and (x['Mo_Final'] > x['Mo_Target']) else 0, axis=1).sum()
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Mo_defects']=deffects 
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Total_defects']+=deffects
    deffects = data.agg(lambda x: 1 if x['LFVD_ShiftHead']==emp and (x['V_Final'] > x['V_Last_EOP']) and (x['V_Final'] > x['V_Target']) else 0, axis=1).sum()
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'V_defects']=deffects 
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Total_defects']+=deffects
    deffects = data.agg(lambda x: 1 if x['LFVD_ShiftHead']==emp and (x['W_Final'] > x['W_Last_EOP']) and (x['W_Final'] > x['W_Target']) else 0, axis=1).sum()
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'W_defects']=deffects
    data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Total_defects']+=deffects

for emp in data_unique_emp:
    fig.add_trace(go.Bar(x=[emp], y=[data_unique_emp.loc[data_unique_emp['LFVD_ShiftHead']==emp, 'Total_defects']], name=f'Гистограмма дефектов для {emp}'))
    

fig.show()
display(data_unique_emp)



### Какая стоимость перерасхода если нам удастся обеспечить среднее значение между Cr_LowerLimit и Cr_Target?

### Выполните расчеты для каждого элемента: Mo, Ni, V, W

In [2]:
import pandas as pd
import dtreeviz
from sklearn.tree import DecisionTreeClassifier


random_state=42
data=pd.read_csv('итоговая таблица_испр.csv',sep=';')
data.fillna(0,inplace=True)
#display(data)
data['quality']=data.apply(lambda x: 1 if x['Cr_Final']<=x['Cr_Target'] else 0,axis=1)

X=data.drop(['HeatNo','quality','Date','Cr_Final','Ni_Final','Mo_Final','V_Final','W_Final'],axis=1).values
y=data['quality'].values

features=data.drop(['HeatNo','Date','Cr_Final','Ni_Final','Mo_Final','V_Final','W_Final'],axis=1).columns.tolist()
class_names=list(set(y))
target='quality'
tree_classifier = DecisionTreeClassifier(max_depth=33, random_state=random_state)
tree_classifier.fit(X, y)

viz_model = dtreeviz.model(tree_classifier,
                           X_train=X, y_train=y,
                           feature_names=features,
                           target_name=target)

viz_model.view(scale=0.8)
#viz_model.save('dtreeviz.svg')

In [ ]:
import pandas as pd
import dtreeviz
from sklearn.tree import DecisionTreeClassifier

pd.set_option('display.max_columns', 500)
pd.set_option('display.max_rows', 100)
pd.set_option('display.width', 1000)


random_state=42
data=pd.read_csv('итоговая таблица_испр.csv',sep=';')
trees = []
data.fillna(0,inplace=True)
#display(data)
qual = [('Cr', 'Cr_Final', 'Cr_Target'), ('Ni', 'Ni_Final', 'Ni_Target'), ('Mo', 'Mo_Final', 'Mo_Target'), ('V', 'V_Final', 'V_Target'), ('W', 'W_Final', 'W_Target')]
for i in range(5):
    data['quality']=data.apply(lambda x: 1 if x[qual[i][1]]<=x[qual[i][2]] else 0,axis=1)
    X=data.drop(['HeatNo','quality','Date','Cr_Final','Ni_Final','Mo_Final','V_Final','W_Final'],axis=1).values
    y=data['quality'].values
    features=data.drop(['HeatNo','Date','Cr_Final','Ni_Final','Mo_Final','V_Final','W_Final'],axis=1).columns.tolist()
    class_names=list(set(y))
    target='quality'
    tree_classifier = DecisionTreeClassifier(max_depth=33, random_state=random_state)
    trees.append((qual[i][0], tree_classifier.fit(X, y)))
print('Деревья обучены')


[('Cr', DecisionTreeClassifier(max_depth=33, random_state=42)), ('Ni', DecisionTreeClassifier(max_depth=33, random_state=42)), ('Mo', DecisionTreeClassifier(max_depth=33, random_state=42)), ('V', DecisionTreeClassifier(max_depth=33, random_state=42)), ('W', DecisionTreeClassifier(max_depth=33, random_state=42))]


In [ ]:
# import random as rnd #for silngle test

data=pd.read_csv("итоговая таблица_испр.csv", sep = ";")
X_new = data.drop(['Date','Cr_Final','Ni_Final','Mo_Final','V_Final','W_Final'],axis=1)
X_user = pd.DataFrame()

display(X_new.head(3))
best_HeatNo = pd.DataFrame(columns=['HeatNo','CrQuality','NiQuality','MoQuality','VQuality','WQuality'])

for i in range(len(data)):
    HeatNo = data.iloc[i]['HeatNo']
    X_new = pd.DataFrame(data.iloc[i].drop(['HeatNo','Date','Cr_Final','Ni_Final','Mo_Final','V_Final','W_Final'],axis=0)).T.values.tolist()
    for j in trees:
        tree_classifier = j[1]
        ans = tree_classifier.predict(X_new)
        best_HeatNo.loc[i, 'HeatNo'] = HeatNo
        best_HeatNo.loc[i, j[0]+'Quality'] = ans[0]

print('Качество плавок по каждой плавке:')
display(best_HeatNo)

display(best_HeatNo[best_HeatNo['CrQuality']==1]['HeatNo'])

#tree_classifier.predict(X_new)

,HeatNo,TotalIngotsWeight,PouringScrap,OtherScrap,Last_EOP,Cr_Last_EOP,Ni_Last_EOP,Mo_Last_EOP,V_Last_EOP,W_Last_EOP,Cr_LowerLimit,Cr_Target,Cr_UpperLimit,Ni_LowerLimit,Ni_Target,Ni_UpperLimit,Mo_LowerLimit,Mo_Target,Mo_UpperLimit,V_LowerLimit,V_Target,V_UpperLimit,W_LowerLimit,W_Target,W_UpperLimit,LFVD_AlBloki,LFVD_AlGran,LFVD_Boksit,LFVD_CaO,LFVD_CASIfi13,LFVD_Cfi13,LFVD_EPŽŽlindra,LFVD_FeAl,LFVD_FeCrA,LFVD_FeCrC,LFVD_FeCrCSi,LFVD_FeCrC51,LFVD_FeMnC,LFVD_FeMo,LFVD_FeS,LFVD_FeSi,LFVD_FeV,LFVD_FeW72,LFVD_KarboritMleti,LFVD_MnMet,LFVD_NiGran,LFVD_Polymox,LFVD_SŽica,LFVD_SiMn,LFVD_SLAGMAG65B,LFVD_AlŽica,LFVD_AlOplašèenaŽica,LFVD_BelaŽlindra,LFVD_KalcijevKarbid,LFVD_SintŽlindra,PV_PT181,PV_OH252,PV_OH255,PV_EMCR,PV_VCMO230,PV_31CRV3,PV_OCR12,PV_OCR12SP,PV_CRV,PV_OCR12VM,PV_UTOPMO2,PV_UTOPMO4,PV_PK2,PV_PK5,PV_PK5M,PV_CRMO_OSTRUŽKI,PV_OCR12VM_OSTRUŽKI,PV_E3,PV_E6,PV_E8
0,73579,49440.0,600.0,2000.0,2.0,9.71,0.20,0.12,0.03,0.01,11.1,11.26,11.75,0,0,0.25,0.7,0.73,0.8,0.9,0.93,1.0,0,0,0.2,26,0,200,600,16.5,20.6,0,0,0,2400,0,0,20,520,0,130,580,0,125,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,40000,0,0
1,73580,46800.0,1000.0,100.0,3.0,12.41,0.16,0.08,0.04,0.01,11.5,11.65,12.00,0,0,0.30,0.7,0.73,0.8,0.9,0.95,1.0,0,0,0.2,20,0,100,500,16.5,0.0,0,0,0,1200,0,0,100,625,0,55,135,0,0,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,40200,0,0
2,73581,45320.0,800.0,2000.0,3.0,11.24,0.17,0.07,0.04,0.01,11.5,11.65,12.00,0,0,0.30,0.7,0.73,0.8,0.9,0.95,1.0,0,0,0.2,15,0,70,400,16.5,0.0,0,0,0,2000,0,0,0,490,0,80,520,0,50,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,40200,0,0


Наиболее подходящие плавки для достижения цели:


,HeatNo,CrQuality,NiQuality,MoQuality,VQuality,WQuality
0,73579,0,0,1,1,0
1,73580,0,0,0,1,0
2,73581,1,0,1,1,0
3,73589,1,0,1,1,0
4,73590,1,0,1,1,0
...,...,...,...,...,...,...
3220,98222,0,0,0,1,0
3221,98223,1,0,0,0,0
3222,98244,0,0,1,1,0
3223,98254,1,0,1,0,0


2       73581
3       73589
4       73590
5       73597
6       73598
        ...  
3218    98212
3219    98221
3221    98223
3223    98254
3224    98255
Name: HeatNo, Length: 1895, dtype: object

Не понимаю как отфильтровать значения ближайшие к параметрам

In [188]:
display(data[data['HeatNo']==best_HeatNo['HeatNo']])

,HeatNo,Date,TotalIngotsWeight,PouringScrap,OtherScrap,Last_EOP,Cr_Last_EOP,Cr_Final,Ni_Last_EOP,Ni_Final,Mo_Last_EOP,Mo_Final,V_Last_EOP,V_Final,W_Last_EOP,W_Final,Cr_LowerLimit,Cr_Target,Cr_UpperLimit,Ni_LowerLimit,Ni_Target,Ni_UpperLimit,Mo_LowerLimit,Mo_Target,Mo_UpperLimit,V_LowerLimit,V_Target,V_UpperLimit,W_LowerLimit,W_Target,W_UpperLimit,LFVD_AlBloki,LFVD_AlGran,LFVD_Boksit,LFVD_CaO,LFVD_CASIfi13,LFVD_Cfi13,LFVD_EPŽŽlindra,LFVD_FeAl,LFVD_FeCrA,LFVD_FeCrC,LFVD_FeCrCSi,LFVD_FeCrC51,LFVD_FeMnC,LFVD_FeMo,LFVD_FeS,LFVD_FeSi,LFVD_FeV,LFVD_FeW72,LFVD_KarboritMleti,LFVD_MnMet,LFVD_NiGran,LFVD_Polymox,LFVD_SŽica,LFVD_SiMn,LFVD_SLAGMAG65B,LFVD_AlŽica,LFVD_AlOplašèenaŽica,LFVD_BelaŽlindra,LFVD_KalcijevKarbid,LFVD_SintŽlindra,PV_PT181,PV_OH252,PV_OH255,PV_EMCR,PV_VCMO230,PV_31CRV3,PV_OCR12,PV_OCR12SP,PV_CRV,PV_OCR12VM,PV_UTOPMO2,PV_UTOPMO4,PV_PK2,PV_PK5,PV_PK5M,PV_CRMO_OSTRUŽKI,PV_OCR12VM_OSTRUŽKI,PV_E3,PV_E6,PV_E8
0,73579,2004-07-27 00:17:10,49440.0,600.0,2000.0,2.0,9.7100,11.30,0.2000,0.21,0.1200,0.71,0.0300,0.90,0.0100,0.02,11.1,11.26,11.75,0,0,0.25,0.7,0.73,0.80,0.90,0.93,1.00,0,0,0.20,26,0,200,600,16.5,20.6,0,0,0,2400,0,0,20,520,0,130,580,0,125,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,40000,0,0
1,73580,2004-07-27 02:18:07,46800.0,1000.0,100.0,3.0,12.4100,11.75,0.1600,0.16,0.0800,0.85,0.0400,0.29,0.0100,0.02,11.5,11.65,12.00,0,0,0.30,0.7,0.73,0.80,0.90,0.95,1.00,0,0,0.20,20,0,100,500,16.5,0.0,0,0,0,1200,0,0,100,625,0,55,135,0,0,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,40200,0,0
2,73581,2004-07-27 04:46:58,45320.0,800.0,2000.0,3.0,11.2400,11.63,0.1700,0.18,0.0700,0.72,0.0400,0.91,0.0100,0.02,11.5,11.65,12.00,0,0,0.30,0.7,0.73,0.80,0.90,0.95,1.00,0,0,0.20,15,0,70,400,16.5,0.0,0,0,0,2000,0,0,0,490,0,80,520,0,50,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,40200,0,0
3,73589,2004-07-28 03:42:29,46800.0,1000.0,800.0,3.0,11.8700,11.60,0.1700,0.17,0.0800,0.73,0.0400,0.92,0.0100,0.01,11.5,11.65,12.00,0,0,0.30,0.7,0.73,0.80,0.90,0.95,1.00,0,0,0.20,20,0,200,400,16.5,20.6,0,0,0,1450,0,0,60,515,0,80,565,0,60,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,0,40200,0,0
4,73590,2004-07-28 05:32:32,48410.0,800.0,2000.0,2.0,10.0200,11.29,0.2100,0.21,0.4800,0.73,0.3500,0.74,0.1100,0.12,11.1,11.36,11.75,0,0,0.25,0.7,0.73,0.85,0.72,0.76,0.85,0,0,0.15,20,0,100,400,16.5,0.0,0,0,0,1250,0,0,0,235,0,40,280,0,50,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,25000,0,0,0,0,0,0,5000,0,15200,0
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
3220,98222,2014-12-18 12:30:07,47380.0,800.0,900.0,2.0,11.0977,11.42,0.1289,0.14,0.4968,0.75,0.2922,0.75,0.0291,0.01,11.1,11.36,11.75,0,0,0.30,0.7,0.73,0.85,0.72,0.76,0.85,0,0,0.20,5,10,160,450,14.3,5.5,0,0,0,290,0,0,40,175,0,30,266,0,50,0,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,15000,0,0,0,0,0,0,5000,0,24000,0
3221,98223,2014-12-18 14:13:33,47360.0,400.0,900.0,2.0,10.5393,11.30,0.1261,0.13,0.6600,0.76,0.2185,0.77,0.0077,0.04,11.1,11.36,11.75,0,0,0.25,0.7,0.73,0.85,0.72,0.76,0.85,0,0,0.15,5,10,310,600,15.2,0.0,0,0,500,16,0,0,0,51,0,0,337,0,0,60,0,0,0.0,0,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,15000,0,0,0,0,0,0,5000,0,24500,0
3222,98244,2014-12-20 12:46:39,44400.0,600.0,300.0,2.0,9.3272,12.07,0.1462,0.15,0.8268,0.99,0.2198,0.75,0.0280,0.02,11.7,12.00,12.30,0,0,0.30,0.9,1.00,1.10,0.70,0.75,0.80,0,0,0.20,13,0,480,850,14.3,7.4,0,0,0,1960,0,0,128,113,0,100,328,0,50,0,0,0,0.0,40,0,0.0,0.0,0,0,0,0,0,0,0,0,0,0,0,0,15000,0,0,0,0,0,0,5000,0,22000,0
3223,98254,2014-12-21 14:47:16,48410.0,800.0,700.0,2.0,10.5762,11.29,0.1635,0.16,0.7249,0.72,0.2418,0.77,0.0161,0.03,11.1,11.46,11.75,0,0,0.25,0.7,0.73,0.85,0.72,0.76,0.85,0,0,0.15,22,0,200,700,14.0,23.9,0,0,0,650,0,0,48,20,0,60,310,0,60,0,0,